# Spatial Data Interpolation Pipeline — Bilinear & Kriging

This notebook provides an **extensible** spatial data interpolation framework:
- Input data is flexibly defined through a configuration file, supporting CSV / Excel and other formats
- Provides both **bilinear interpolation** and **kriging interpolation** for manual selection
- Includes a **special dataset post-processing module**: e.g., invert LAB depth to a positive value and convert the unit from m to km
- When saving results, **only the data column name is used as the title** (the dataset name prefix is automatically removed)


## 1. Environment Setup and Library Imports


In [1]:
# ==================== 1. Environment setup and library imports ====================
import numpy as np
import pandas as pd
import matplotlib.pyplot as plt
import warnings
from pathlib import Path
import pyproj; pyproj.datadir.set_data_dir(r'C:\Users\19023\anaconda3\envs\KanSHF\Library\share\proj')

# Interpolation core
from scipy.interpolate import griddata, RegularGridInterpolator

# Kriging — requires pykrige: pip install pykrige
try:
    from pykrige.ok import OrdinaryKriging
    HAS_PYKRIGE = True
except ImportError:
    HAS_PYKRIGE = False
    print("⚠ 未安装 pykrige，克里金方法不可用。请执行: pip install pykrige")

warnings.filterwarnings('ignore')

# Global plotting settings
plt.rcParams['font.family'] = ['Times New Roman', 'FangSong', 'SimHei', 'Microsoft YaHei']
plt.rcParams['axes.unicode_minus'] = False
plt.rcParams['figure.dpi'] = 800

print("✅ 环境配置完成")
print(f"   双线性插值 (scipy.griddata): ✓")
print(f"   克里金插值 (pykrige):        {'✓' if HAS_PYKRIGE else '✗ (未安装)'}")


c:\Users\19023\anaconda3\envs\KanSHF\Lib\site-packages\pyproj\network.py:59: UserWarning: pyproj unable to set PROJ database path.
  _set_context_ca_bundle_path(ca_bundle_path)


✅ 环境配置完成
   双线性插值 (scipy.griddata): ✓
   克里金插值 (pykrige):        ✓


## 2. Extensible Input Data Definition

Configure all datasets to be processed here. Two types are supported:
- **`data_type: 'raster'`** — Raster/scattered data; provides latitude/longitude columns and value columns, interpolated onto a grid
- **`data_type: 'vector_line'`** — Line vector data (.shp/.dig); computes the distance from each grid point to the nearest / top-5 nearest lines

Extend the framework by simply adding a new entry to the `DATASET_CONFIG` dictionary.
Optional field `post_process`: specifies a special post-processing transform for this dataset (see **2d Special Dataset Processing Module**).
Currently supported: `'lab_depth_to_km'` — invert LAB depth to a positive value and divide by 1000 to convert the unit from m to km.


In [2]:
# ==================== 2. Extensible dataset configuration ====================
# Define all datasets in this dictionary; to add new data, just add one entry

DATASET_CONFIG = {
    # ============ Raster / scattered datasets (data_type='raster') ============
    # lat_col / lon_col optional: auto-detected when not specified (Lat/lat/Latitude, Lon/lon/Long/Longitude)
    'EMAG': { # Magnetic anomaly dataset
        'data_type': 'raster',
        'path': '../data/EMAG.xls',
        'file_type': 'excel',
        'value_cols': ['Magnetic_Anomaly_Value(nT)'],
        'interp_method': 'bilinear',
        'kriging_pre_filter': True,
        'kriging_filter_margin': 1.0,
    },
    'DEM': { # Digital elevation model dataset
        'data_type': 'raster',
        'path': '../data/DEM.xls',
        'file_type': 'excel',
        'value_cols': ['DEM'],
        'interp_method': 'bilinear',
        'kriging_pre_filter': False,
        'kriging_filter_margin': 1.0,
    },
    'GRD': { # Gravity anomaly dataset
        'data_type': 'raster',
        'path': '../data/gravityAnomaly.xlsx',
        'file_type': 'excel',
        'value_cols': ['RASTERVALU'],
        'interp_method': 'bilinear',
        'kriging_pre_filter': True,
        'kriging_filter_margin': 1.0,
    },
    'CPD': { # Curie point depth dataset
        'data_type': 'raster',
        'path': '../data/cpd.csv',
        'file_type': 'csv',
        'value_cols': ['cpd'],
        'interp_method': 'kriging',
        'kriging_pre_filter': True,
        'kriging_filter_margin': 1.5,
    },
    'LAB': { # Lithosphere-asthenosphere boundary depth dataset
        'data_type': 'raster',
        'path': '../data/LAB_extracted.csv',
        'file_type': 'csv',
        'value_cols': ['LAB'],
        'interp_method': 'kriging',
        'kriging_pre_filter': True,
        'kriging_filter_margin': 2.0,
        'post_process': 'lab_depth_to_km',  # special processing: invert to positive + m→km
        'outlier_filter': {'method': 'mad', 'k': 5},   # remove isolated extreme points to avoid patches
        'post_smoothing': {'sigma': 1.0},              # Gaussian smoothing after interpolation (removes small-scale patches)
    },
    'Thermal_conductivity': { # Thermal conductivity dataset
        'data_type': 'raster',
        'path': '../data/Updated heat flow data in china.csv',
        'file_type': 'csv',
        'value_cols': ['Thermal Conductivity （mW/K/m/）'],
        'interp_method': 'kriging',
        'kriging_pre_filter': False,
        'kriging_filter_margin': 0,
        'lat_col': 'North latitude',          # optional: auto-detects Lat/lat/Latitude
        'lon_col': 'East longitude',          # optional: auto-detects Lon/lon/
    },
    'CRST1.0': { # Crustal structure dataset
        'data_type': 'raster',
        'path': '../data/CRUST1.0/crust1.0-xyz/crust1_merged.csv',
        'file_type': 'csv',
        'value_cols': ['crsthk','sedthk-m','bd6','bd7','bd8','bd9','ro6','ro7','ro8','ro9','vp6','vp7','vp8','vp9','vs6','vs7','vs8','vs9'],
        'interp_method': 'kriging',
        'kriging_pre_filter': True,
        'kriging_filter_margin': 4.0,
    },
    'GRD': { # Gravity anomaly dataset
        'data_type': 'raster',
        'path': '../data/gravityAnomaly.xlsx',
        'file_type': 'excel',
        'value_cols': ['RASTERVALU'],
        'interp_method': 'bilinear',
        'kriging_pre_filter': True,
        'kriging_filter_margin': 1.0,
    },
    'CTC': {
        'data_type': 'raster',
        'path': '../data/CrustalThiChina.xlsx',
        'file_type': 'excel',
        'value_cols': ['H(km)'],
        'interp_method': 'kriging',
        'kriging_pre_filter': True,
        'kriging_filter_margin': 3.0,
        'outlier_filter': {'method': 'mad', 'k': 5},   # remove isolated extreme points to avoid patches
        'post_smoothing': {'sigma': 1.0},              # Gaussian smoothing after interpolation (removes small-scale patches)
    },
    # ============ Line vector datasets (data_type='vector_line') ============
    'FAULT': { # Fault dataset
        'data_type': 'vector_line',
        'path': '../data/CAFD400_V2023.shp',
        'distance_method': 'top5_mean',       # 'nearest' or 'top5_mean'
        'output_cols': ['DTF'],             # output column names (nearest=1 col, top5_mean=1 col)
    },
    'ridge': { # Mid-ocean ridge dataset
        'data_type': 'vector_line',
        'path': '../data/UTIGTR_0174_presentday_pb/UTIGTR_0174_presentday_pb/PLATES_PlateBoundary_ArcGIS/ridge.shp',
        'distance_method': 'nearest',
        'output_cols': ['DTR'],
    },
    # ---- Templates ----
    # 'NEW_RASTER': {
    #     'data_type': 'raster',
    #     'path': '../data/your_data.csv',
    #     'file_type': 'csv',          # csv / xls / xlsx
    #     # 'lat_col': 'Lat',          # optional: auto-detects Lat/lat/Latitude
    #     # 'lon_col': 'Lon',          # optional: auto-detects Lon/lon/Long/Longitude
    #     'value_cols': ['col1', 'col2'],
    #     'interp_method': 'bilinear',
    #     'kriging_pre_filter': True,
    #     'kriging_filter_margin': 1.0,
    #     # 'post_process': 'lab_depth_to_km',  # optional: special post-processing (LAB invert + m→km)
    # },
    # 'NEW_LINE': {
    #     'data_type': 'vector_line',
    #     'path': '../data/your_lines.shp',
    #     'distance_method': 'nearest',      # 'nearest' | 'top5_mean'
    #     'output_cols': ['DIST'],
    # },
}

print(f"已配置 {len(DATASET_CONFIG)} 个数据集: {list(DATASET_CONFIG.keys())}")


已配置 10 个数据集: ['EMAG', 'DEM', 'GRD', 'CPD', 'LAB', 'Thermal_conductivity', 'CRST1.0', 'CTC', 'FAULT', 'ridge']


In [3]:
# ==================== 2b. Data loading functions ====================
def _read_csv_with_encoding_fallback(path):
    """Read a CSV file trying multiple encodings."""
    for enc in ['utf-8', 'gbk', 'gb2312', 'latin-1', 'ISO-8859-1']:
        try:
            return pd.read_csv(path, encoding=enc)
        except (UnicodeDecodeError, UnicodeError):
            continue
    raise ValueError(f"无法用常见编码读取: {path}")


def load_dataset(config):
    """
    Load a single raster/scattered dataset from its configuration.

    Supports file_type: 'csv', 'xls', 'xlsx', 'excel' (xls/xlsx compatible).
    lat_col / lon_col optional: auto-detected from common column names when not specified.
    Returns: (DataFrame, lat_col, lon_col, value_cols)
    """
    path = config['path']
    file_type = config.get('file_type', 'auto')

    if file_type == 'csv':
        df = _read_csv_with_encoding_fallback(path)
    elif file_type in ('xls', 'xlsx', 'excel'):
        df = pd.read_excel(path)
    else:
        raise ValueError(f"不支持的文件类型: {file_type}，可选: csv, xls, xlsx, excel")

    # ---- Auto-detect or use specified lat/lon column names ----
    LAT_CANDIDATES = ['Lat', 'lat', 'Latitude', 'latitude', 'LAT']
    LON_CANDIDATES = ['Lon', 'lon', 'Long', 'long', 'Longitude', 'longitude', 'LON', 'LONG']

    lat_col = config.get('lat_col', None)
    lon_col = config.get('lon_col', None)

    if lat_col is None:
        lat_col = next((c for c in LAT_CANDIDATES if c in df.columns), None)
        if lat_col is None:
            raise ValueError(f"无法自动检测纬度列，可用列: {list(df.columns)}。"
                             f"请在配置中手动指定 'lat_col'。")
        print(f"  🔍 自动检测纬度列: '{lat_col}'")

    if lon_col is None:
        lon_col = next((c for c in LON_CANDIDATES if c in df.columns), None)
        if lon_col is None:
            raise ValueError(f"无法自动检测经度列，可用列: {list(df.columns)}。"
                             f"请在配置中手动指定 'lon_col'。")
        print(f"  🔍 自动检测经度列: '{lon_col}'")

    value_cols = config['value_cols']

    # Check that the columns exist
    required = [lat_col, lon_col] + value_cols
    missing = [c for c in required if c not in df.columns]
    if missing:
        print(f"⚠ 数据集缺少列: {missing}，可用列: {list(df.columns)}")

    # Drop rows with NaN
    before = len(df)
    df = df.dropna(subset=[lat_col, lon_col] + value_cols, how='any')
    after = len(df)
    # ---- Optional outlier filtering (removes isolated extreme points to avoid "bullseye" patches in
    #      kriging/bilinear interpolation) ----
    # Enabled via config['outlier_filter']; applies only to single-value-column datasets.
    # method: 'mad' (median ± k×MAD) | 'percentile' (pmin~pmax percentile) | 'std' (median ± k×std)
    outlier_cfg = config.get('outlier_filter', None)
    if outlier_cfg and len(value_cols) == 1:
        _v = value_cols[0]
        _z = df[_v].to_numpy(dtype=float)
        _ok = np.isfinite(_z)
        _method = outlier_cfg.get('method', 'mad')
        if _method == 'mad':
            _k = outlier_cfg.get('k', 5)
            _med = np.nanmedian(_z)
            _mad = np.nanmedian(np.abs(_z - _med))
            if not (_mad > 0):
                _mad = np.nanstd(_z) if np.nanstd(_z) > 0 else 1.0
            _keep = _ok & (np.abs(_z - _med) <= _k * _mad)
        elif _method == 'percentile':
            _pmin, _pmax = outlier_cfg.get('pmin', 1), outlier_cfg.get('pmax', 99)
            _lo, _hi = np.nanpercentile(_z, [_pmin, _pmax])
            _keep = _ok & (_z >= _lo) & (_z <= _hi)
        else:  # 'std'
            _k = outlier_cfg.get('k', 5)
            _med = np.nanmedian(_z); _sd = np.nanstd(_z)
            if not (_sd > 0):
                _sd = 1.0
            _keep = _ok & (np.abs(_z - _med) <= _k * _sd)
        _n_rem = int((~_keep).sum())
        if _n_rem > 0:
            df = df[_keep].copy()
            print(f"  🔽 离群值过滤[{value_cols[0]}]: 剔除 {_n_rem} 个点 (method={_method})")

    return df, lat_col, lon_col, value_cols


# ==================== 2c. Line vector loading and distance computation ====================
def load_line_dataset(path):
    """
    Load a line vector file (supports .shp and .dig).
    .shp prefers geopandas, falling back to a manual binary parser.
    Returns: a list of shapely LineString/MultiLineString
    """
    from shapely.geometry import LineString, MultiLineString

    ext = Path(path).suffix.lower()

    if ext == '.shp':
        # Try reading with geopandas
        try:
            import geopandas as gpd
            gdf = gpd.read_file(path)
            geoms = []
            for g in gdf.geometry:
                try:
                    if g is not None and not g.is_empty:
                        geoms.append(g)
                except Exception:
                    continue  # skip geometries that cannot be checked
            if geoms:
                print(f"  加载 {len(geoms)} 条线要素 (shp, gpd)")
                return geoms
        except Exception as e:
            print(f"  geopandas 读取失败 ({e}), 回退到二进制解析...")

        # Fallback: manual binary parsing (more format compatible)
        geoms = _read_shp_lines_binary(path)
        print(f"  加载 {len(geoms)} 条线要素 (shp, binary)")
        return geoms

    elif ext == '.dig':
        geoms = _parse_dig_file(path)
        print(f"  加载 {len(geoms)} 个步长 (dig)")
        return geoms

    else:
        raise ValueError(f"不支持的线矢量格式: {ext} (仅支持 .shp, .dig)")


def _read_shp_lines_binary(shp_path):
    """
    Read all line features from a .shp file in binary (fallback).
    Returns a list of shapely LineString/MultiLineString.
    """
    import struct
    from shapely.geometry import LineString, MultiLineString

    geoms = []
    with open(shp_path, 'rb') as f:
        f.seek(100)  # skip the file header
        while True:
            head = f.read(8)
            if len(head) < 8:
                break
            rec_num, content_len_words = struct.unpack('>ii', head)
            content_len = content_len_words * 2
            content = f.read(content_len)
            if len(content) < content_len:
                break

            shape_type = struct.unpack('<i', content[:4])[0]
            if shape_type not in (3, 13, 23):  # Polyline, PolylineZ, PolylineM
                continue

            offset = 4 + 4 * 8  # skip shape_type + bbox
            numParts, numPoints = struct.unpack('<ii', content[offset:offset+8])
            offset += 8
            parts = struct.unpack(f'<{numParts}i', content[offset:offset+4*numParts])
            offset += 4 * numParts

            points = []
            for i in range(numPoints):
                x, y = struct.unpack('<dd', content[offset + i*16 : offset + i*16 + 16])
                points.append((x, y))

            lines = []
            for i in range(numParts):
                start = parts[i]
                end = parts[i+1] if i+1 < numParts else numPoints
                seg = points[start:end]
                if len(seg) >= 2:
                    lines.append(LineString(seg))
            if lines:
                geoms.append(MultiLineString(lines) if len(lines) > 1 else lines[0])
    return geoms


def _parse_dig_file(file_path):
    """Parse a PB2002 .dig file and return a list of LineString."""
    from shapely.geometry import LineString

    segments = []
    with open(file_path, 'r', encoding='utf-8') as f:
        current_points = []
        for line in f:
            line = line.strip()
            if not line:
                continue
            if line.startswith('*** end of line segment ***'):
                if len(current_points) >= 2:
                    segments.append(LineString(current_points))
                current_points = []
                continue
            # Try to parse a coordinate line
            if ',' in line:
                parts = line.split(',')
            elif line[0].isalpha() and len(line) >= 5 and line[2] in '-/\\\\':
                # header line, skip
                continue
            else:
                continue
            try:
                lon = float(parts[0])
                lat = float(parts[1])
                current_points.append((lon, lat))
            except (ValueError, IndexError):
                continue
        # end of file
        if len(current_points) >= 2:
            segments.append(LineString(current_points))
    return segments


def compute_line_distance(geoms, target_lons, target_lats, method='nearest'):
    """
    Compute the distance from grid points to a set of line geometries.

    Args:
        geoms:        list of shapely line geometries
        target_lons:  target longitude array (1D)
        target_lats:  target latitude array (1D)
        method:       'nearest' — distance to the nearest line
                      'top5_mean' — mean distance to the top-5 nearest lines

    Returns:
        distances: numpy array of shape (len(target_lats), len(target_lons))
        (with method='top5_mean' a second array is also returned)
    """
    from shapely.geometry import Point

    grid_lon, grid_lat = np.meshgrid(target_lons, target_lats)
    n_rows, n_cols = grid_lon.shape

    if method == 'nearest':
        dist_grid = np.full((n_rows, n_cols), np.nan)
        for i in range(n_rows):
            for j in range(n_cols):
                pt = Point(grid_lon[i, j], grid_lat[i, j])
                min_d = min(pt.distance(g) for g in geoms)
                dist_grid[i, j] = min_d
        return dist_grid

    elif method == 'top5_mean':
        dist_grid = np.full((n_rows, n_cols), np.nan)
        for i in range(n_rows):
            for j in range(n_cols):
                pt = Point(grid_lon[i, j], grid_lat[i, j])
                all_dists = sorted(pt.distance(g) for g in geoms)
                dist_grid[i, j] = np.mean(all_dists[:5]) if len(all_dists) >= 5 else np.mean(all_dists)
        return dist_grid

    else:
        raise ValueError(f"未知距离方法: '{method}'，可选: 'nearest' | 'top5_mean'")


print("🔧 线矢量加载与距离计算函数已定义")
print("   load_line_dataset()     — 加载 .shp / .dig 线文件")
print("   compute_line_distance() — 计算网格点到线距离 (nearest / top5_mean)")


def load_all_datasets(config_dict):
    """
    Batch load all datasets.
    Returns:
        raster_datasets:  {name: (df, lat_col, lon_col, value_cols)}   raster/scattered data
        line_datasets:    {name: (geoms, distance_method, output_cols)}  line vector data
    """
    raster_datasets = {}
    line_datasets = {}

    for name, cfg in config_dict.items():
        data_type = cfg.get('data_type', 'raster')

        if data_type == 'raster':
            try:
                df, lat_col, lon_col, value_cols = load_dataset(cfg)
                raster_datasets[name] = (df, lat_col, lon_col, value_cols)
                print(f"✓ {name} [raster]: {len(df)} 条记录, 值列: {value_cols}")
            except FileNotFoundError:
                print(f"✗ {name}: 文件不存在 — {cfg['path']}")
            except Exception as e:
                print(f"✗ {name}: 加载失败 — {e}")

        elif data_type == 'vector_line':
            try:
                geoms = load_line_dataset(cfg['path'])
                line_datasets[name] = (geoms, cfg['distance_method'], cfg['output_cols'])
                print(f"✓ {name} [line]: {len(geoms)} 条线要素, 方法: {cfg['distance_method']}")
            except FileNotFoundError:
                print(f"✗ {name}: 文件不存在 — {cfg['path']}")
            except Exception as e:
                print(f"✗ {name}: 加载失败 — {e}")

    return raster_datasets, line_datasets


# ---- Uncomment to actually load the data ----
# raster_datasets, line_datasets = load_all_datasets(DATASET_CONFIG)
print("🔧 数据加载函数已定义，暂未执行实际加载。")


🔧 线矢量加载与距离计算函数已定义
   load_line_dataset()     — 加载 .shp / .dig 线文件
   compute_line_distance() — 计算网格点到线距离 (nearest / top5_mean)
🔧 数据加载函数已定义，暂未执行实际加载。


## 2d. Special Dataset Processing Module

Applies additional post-processing transforms to certain special datasets **after interpolation**.
- Specify the processor name in the `post_process` field of `DATASET_CONFIG` (e.g., `'lab_depth_to_km'`)
- The processor transforms the interpolation result (grid or scattered array) element-wise
- Built-in: `'lab_depth_to_km'` — invert LAB depth to a positive value, then divide by 1000 to convert the unit from m to km
- Extend by registering new functions in `SPECIAL_PROCESSORS`


In [4]:
# ==================== 2d. Special dataset processing module ====================
# Applies extra post-processing transforms to special datasets after interpolation.
# Usage: add 'post_process': <processor_name> to a DATASET_CONFIG entry.
# Processor function signature: func(values: np.ndarray) -> np.ndarray, element-wise transform.

SPECIAL_PROCESSORS = {
    # LAB depth: original values are negative (m); invert to positive depth, then /1000 to km
    'lab_depth_to_km': {
        'description': 'LAB 深度: 取反(转正值) + m→km (/1000)',
        'func': lambda x: (-x) / 1000.0,
    },
}


def apply_special_processing(values, processor_key, dataset_name=''):
    """
    Apply a special post-processing transform to interpolation results.

    Args:
        values:        interpolated result array (2D grid or 1D scattered)
        processor_key: processor name; None means no processing
        dataset_name:  dataset name (used only for logging)

    Returns:
        transformed array (returned unchanged if no processing is needed)
    """
    if processor_key is None:
        return values

    if processor_key not in SPECIAL_PROCESSORS:
        print(f"  ⚠ [{dataset_name}] 未知特殊处理器: '{processor_key}'，已跳过")
        return values

    info = SPECIAL_PROCESSORS[processor_key]
    print(f"  🔄 [{dataset_name}] 特殊处理 '{processor_key}': {info['description']}")
    return info['func'](np.asarray(values))


def make_output_col_name(dataset_name, value_col, result_df):
    """
    Generate the output column name: **keep only the data column name as the title**
    (the dataset name prefix is removed). If different datasets produce a
    colliding value column name (already present), append the dataset name as a suffix.

    Args:
        dataset_name: dataset name (e.g., 'LAB')
        value_col:    original data column name (e.g., 'LAB')
        result_df:    current result DataFrame (used to check name collisions)

    Returns:
        output column name
    """
    col = str(value_col)
    if col not in result_df.columns:
        return col
    alt = f"{col}_{dataset_name}"
    print(f"  ⚠ 列名 '{col}' 冲突，自动改为 '{alt}'")
    return alt


print("✅ 特殊数据集处理模块已定义")
print("   SPECIAL_PROCESSORS['lab_depth_to_km'] — LAB 深度取反转正值 + m→km")
print("   apply_special_processing()            — 对插值结果应用后处理")
print("   make_output_col_name()                — 输出列名仅保留数据列名")


✅ 特殊数据集处理模块已定义
   SPECIAL_PROCESSORS['lab_depth_to_km'] — LAB 深度取反转正值 + m→km
   apply_special_processing()            — 对插值结果应用后处理
   make_output_col_name()                — 输出列名仅保留数据列名


## 3. Bilinear Interpolation

Bilinear interpolation is performed in two steps:
1. Interpolate scattered data to a regular grid using `griddata(method='linear')` (based on Delaunay triangulation, equivalent to bilinear)
2. Fill NaN points outside the convex hull with `method='nearest'`

Also supports re-interpolating from a regular grid to arbitrary scattered points via `RegularGridInterpolator`.


In [5]:
# ==================== 3. Bilinear interpolation ====================
def bilinear_interpolate(df, lat_col, lon_col, value_col,
                         target_lats, target_lons,
                         fill_nan=True):
    """
    Bilinear interpolation: interpolate scattered data onto a regular grid.

    Args:
        df:          DataFrame containing the original data
        lat_col:     latitude column name
        lon_col:     longitude column name
        value_col:   numeric value column to interpolate
        target_lats: target grid latitude array (1D)
        target_lons: target grid longitude array (1D)
        fill_nan:    whether to fill NaN outside the convex hull with nearest neighbor

    Returns:
        z_grid: interpolated result of shape (len(target_lats), len(target_lons))
    """
    # Extract valid data
    mask = df[value_col].notna()
    if mask.sum() < 3:
        print(f"  ⚠ {value_col}: 有效点不足 (<3)，返回 NaN 网格")
        return np.full((len(target_lats), len(target_lons)), np.nan)

    x = df.loc[mask, lon_col].values
    y = df.loc[mask, lat_col].values
    z = df.loc[mask, value_col].values

    try:
        grid_x, grid_y = np.meshgrid(target_lons, target_lats)
        points = np.column_stack([x, y])
        xi = np.column_stack([grid_x.ravel(), grid_y.ravel()])

        # Bilinear interpolation (scipy griddata linear is equivalent to bilinear on a regular grid)
        z_grid = griddata(points, z, xi, method='linear')

        # Fill NaN outside the convex hull with nearest neighbor
        if fill_nan:
            nan_mask = np.isnan(z_grid)
            if nan_mask.any():
                z_nearest = griddata(points, z, xi[nan_mask], method='nearest')
                z_grid[nan_mask] = z_nearest

        z_grid = z_grid.reshape(grid_x.shape)
        return z_grid

    except Exception as e:
        print(f"  ✗ 双线性插值失败 [{value_col}]: {e}")
        return np.full((len(target_lats), len(target_lons)), np.nan)


def bilinear_interpolate_to_points(df, lat_col, lon_col, value_col,
                                    target_lats, target_lons):
    """
    Bilinear interpolation to arbitrary scattered positions (non-regular grid).
    Returns: 1D numpy array, length = len(target_lats)
    """
    mask = df[value_col].notna()
    if mask.sum() < 3:
        return np.full(len(target_lats), np.nan)

    x = df.loc[mask, lon_col].values
    y = df.loc[mask, lat_col].values
    z = df.loc[mask, value_col].values

    try:
        target_points = np.column_stack([target_lons, target_lats])
        z_interp = griddata(
            points=np.column_stack([x, y]),
            values=z,
            xi=target_points,
            method='linear'
        )
        # Fill NaN with nearest neighbor
        nan_mask = np.isnan(z_interp)
        if nan_mask.any():
            z_nearest = griddata(
                points=np.column_stack([x, y]),
                values=z,
                xi=target_points[nan_mask],
                method='nearest'
            )
            z_interp[nan_mask] = z_nearest
        return z_interp
    except Exception as e:
        print(f"  ✗ 散点双线性插值失败 [{value_col}]: {e}")
        return np.full(len(target_lats), np.nan)


print("✅ 双线性插值函数已定义")
print("   bilinear_interpolate()           — 插值到规则网格")
print("   bilinear_interpolate_to_points() — 插值到散点")


✅ 双线性插值函数已定义
   bilinear_interpolate()           — 插值到规则网格
   bilinear_interpolate_to_points() — 插值到散点


## 4. Kriging Interpolation

Uses Ordinary Kriging from `pykrige`.
- Supports multiple variogram models: `spherical`, `exponential`, `gaussian`, `linear`
- Auto-fits or manually specifies variogram parameters
- Outputs the interpolated grid and a variance grid


In [6]:
# ==================== 4. Kriging interpolation ====================
# ★ Local-neighborhood kriging: each target point uses only the closest
#   KRIG_N_CLOSEST data points to solve the kriging system.
#   Compared to the default "global kriging" (all points, long correlation range),
#   local kriging:
#     - fits the local data better, reducing over-smoothing (more "accurate")
#     - is faster
#   Smaller values → closer to the original data (less smooth); larger values → smoother and slower.
#   Recommended 20~60.
KRIG_N_CLOSEST = 20


def kriging_interpolate(df, lat_col, lon_col, value_col,
                        target_lats, target_lons,
                        variogram_model='spherical',
                        nlags=12,
                        weight=True,
                        pre_filter=True,
                        filter_margin=1.0,
                        n_closest=KRIG_N_CLOSEST):
    """
    Ordinary kriging interpolation (local neighborhood): interpolate scattered data onto a regular grid.

    Args:
        df:              DataFrame containing the original data
        lat_col:         latitude column name
        lon_col:         longitude column name
        value_col:       numeric value column to interpolate
        target_lats:     target grid latitude array (1D)
        target_lons:     target grid longitude array (1D)
        variogram_model: variogram model
                         'spherical', 'exponential', 'gaussian', 'linear', 'power'
        nlags:           number of variogram lags
        weight:          whether to use weights (True=ordinary kriging, False=simple kriging)
        pre_filter:      whether to pre-filter data points before interpolation (prevents memory overflow)
        filter_margin:   outward margin for the filter (degrees), default 1.0°
        n_closest:       number of local neighborhood points (closest data points used per target point,
                         default KRIG_N_CLOSEST). Smaller = closer to local data/less smooth;
                         larger = smoother and slower.

    Returns:
        z_grid:  interpolated result of shape (len(target_lats), len(target_lons))
        sigma:   variance grid (only when pykrige is available, otherwise None)
    """
    if not HAS_PYKRIGE:
        raise ImportError("pykrige 未安装。请执行: pip install pykrige")

    # Extract valid data
    mask = df[value_col].notna()
    if mask.sum() < 4:
        print(f"  ⚠ {value_col}: 有效点不足 (<4)，克里金需要至少 4 个点")
        return (np.full((len(target_lats), len(target_lons)), np.nan), None)

    # ---- Pre-filter: keep only data points within the grid extent ± filter_margin ----
    if pre_filter:
        grid_lat_min, grid_lat_max = target_lats.min(), target_lats.max()
        grid_lon_min, grid_lon_max = target_lons.min(), target_lons.max()

        bound_lat_min = grid_lat_min - filter_margin
        bound_lat_max = grid_lat_max + filter_margin
        bound_lon_min = grid_lon_min - filter_margin
        bound_lon_max = grid_lon_max + filter_margin

        spatial_mask = (
            mask &
            (df[lat_col] >= bound_lat_min) & (df[lat_col] <= bound_lat_max) &
            (df[lon_col] >= bound_lon_min) & (df[lon_col] <= bound_lon_max)
        )
        n_filtered = mask.sum() - spatial_mask.sum()
        if n_filtered > 0:
            print(f"  🔽 预过滤: 剔除 {n_filtered} 个网格外点, 保留 {spatial_mask.sum()} 个")
        mask = spatial_mask

        if mask.sum() < 4:
            print(f"  ⚠ {value_col}: 过滤后有效点不足 (<4)")
            return (np.full((len(target_lats), len(target_lons)), np.nan), None)

    x = df.loc[mask, lon_col].values   # longitude
    y = df.loc[mask, lat_col].values   # latitude
    z = df.loc[mask, value_col].values

    try:
        # Create the OrdinaryKriging object (fit variogram)
        OK = OrdinaryKriging(
            x, y, z,
            variogram_model=variogram_model,
            nlags=nlags,
            weight=weight,
            verbose=False,
            enable_plotting=False,
        )

        # Local-neighborhood kriging: each target point uses only the closest n_closest data points
        # (moving-window requires the 'loop' backend)
        k = max(4, min(n_closest, len(x)))
        z_grid, sigma_grid = OK.execute(
            'grid', target_lons, target_lats,
            n_closest_points=k, backend='loop',
        )

        return z_grid, sigma_grid

    except Exception as e:
        print(f"  ✗ 克里金插值失败 [{value_col}]: {e}")
        return (np.full((len(target_lats), len(target_lons)), np.nan), None)


def kriging_interpolate_to_points(df, lat_col, lon_col, value_col,
                                   target_lats, target_lons,
                                   variogram_model='spherical',
                                   nlags=12,
                                   n_closest=KRIG_N_CLOSEST):
    """
    Kriging interpolation to arbitrary scattered positions (local-neighborhood kriging).
    Returns: (z_interp: 1D array, sigma: 1D array or None)
    """
    if not HAS_PYKRIGE:
        raise ImportError("pykrige 未安装。请执行: pip install pykrige")

    mask = df[value_col].notna()
    if mask.sum() < 4:
        return (np.full(len(target_lats), np.nan), None)

    x = df.loc[mask, lon_col].values
    y = df.loc[mask, lat_col].values
    z = df.loc[mask, value_col].values

    try:
        OK = OrdinaryKriging(
            x, y, z,
            variogram_model=variogram_model,
            nlags=nlags,
            verbose=False,
            enable_plotting=False,
        )
        k = max(4, min(n_closest, len(x)))
        z_interp, sigma_interp = OK.execute(
            'points', target_lons, target_lats,
            n_closest_points=k, backend='loop',
        )
        return z_interp, sigma_interp
    except Exception as e:
        print(f"  ✗ 散点克里金插值失败 [{value_col}]: {e}")
        return (np.full(len(target_lats), np.nan), None)


# ---- Available variogram models ----
VARIOGRAM_MODELS = ['spherical', 'exponential', 'gaussian', 'linear', 'power']
print("✅ 克里金插值函数已定义")
print(f"   支持变差函数模型: {VARIOGRAM_MODELS}")
print(f"   局部邻域点数:      {KRIG_N_CLOSEST}（越小越贴合局部数据、更不平滑）")
print("   kriging_interpolate()           — 插值到规则网格")
print("   kriging_interpolate_to_points() — 插值到散点")


✅ 克里金插值函数已定义
   支持变差函数模型: ['spherical', 'exponential', 'gaussian', 'linear', 'power']
   局部邻域点数:      20（越小越贴合局部数据、更不平滑）
   kriging_interpolate()           — 插值到规则网格
   kriging_interpolate_to_points() — 插值到散点


## 5. Interpolation Method Selection

**Raster data**: each dataset independently selects its method via `interp_method` in `DATASET_CONFIG`:
- `'bilinear'` — bilinear interpolation (fast)
- `'kriging'` — kriging interpolation (slower but more accurate), with optional pre-filtering

**Line vector data**: distance computation is selected via `distance_method`:
- `'nearest'` — distance to the nearest line
- `'top5_mean'` — mean distance to the top-5 nearest lines

The kriging variogram model is a global parameter.


In [7]:
# ==================== 5. Interpolation method selection (manual) ====================

# ★ Each dataset's interpolation method and pre-filter toggle are set independently
#   in DATASET_CONFIG (Cell 2) ★
# The kriging variogram model is the only global parameter kept below.

# Kriging variogram model:
# options: 'spherical' | 'exponential' | 'gaussian' | 'linear' | 'power'
VARIOGRAM_MODEL = 'spherical'

# Target grid resolution (degrees)
TARGET_RESOLUTION = 0.2

# Input file paths
SHAPEFILE_PATH = '../data/eastChinaLine.shp'
SHF_PATH = '../data/SHF.csv'

# ---- Print the full configuration of each dataset ----
print("=" * 60)
print("📋 各数据集配置:")
print("=" * 60)
for name, cfg in DATASET_CONFIG.items():
    dtype = cfg.get('data_type', 'raster')
    if dtype == 'raster':
        method = cfg.get('interp_method', 'bilinear')
        pre_filt = cfg.get('kriging_pre_filter', True)
        margin = cfg.get('kriging_filter_margin', 1.0)
        info = f"raster | {method}" + (f" | 预过滤={'ON' if pre_filt else 'OFF'} ±{margin}°" if method == 'kriging' else "")
        post = cfg.get('post_process', None)
        if post is not None:
            info += f" | 特殊处理: {post}"
    elif dtype == 'vector_line':
        info = f"line   | {cfg.get('distance_method', '?')}"
    else:
        info = f"{dtype}"
    print(f"  {name:8s} → {info}")
print(f"\n克里金变差函数模型: {VARIOGRAM_MODEL}")
print(f"目标分辨率:          {TARGET_RESOLUTION}°")
print(f"轮廓文件:            {SHAPEFILE_PATH}")
print(f"热流文件:            {SHF_PATH}")

# ---- Method validation ----
has_kriging = any(cfg.get('interp_method', 'bilinear') == 'kriging' for cfg in DATASET_CONFIG.values())
if has_kriging and not HAS_PYKRIGE:
    raise ImportError("有数据集选择了克里金但 pykrige 未安装。请安装 pykrige 或切换方法。")

print(f"\n🔧 插值引擎就绪")


📋 各数据集配置:
  EMAG     → raster | bilinear
  DEM      → raster | bilinear
  GRD      → raster | bilinear
  CPD      → raster | kriging | 预过滤=ON ±1.5°
  LAB      → raster | kriging | 预过滤=ON ±2.0° | 特殊处理: lab_depth_to_km
  Thermal_conductivity → raster | kriging | 预过滤=OFF ±0°
  CRST1.0  → raster | kriging | 预过滤=ON ±4.0°
  CTC      → raster | kriging | 预过滤=ON ±3.0°
  FAULT    → line   | top5_mean
  ridge    → line   | nearest

克里金变差函数模型: spherical
目标分辨率:          0.2°
轮廓文件:            ../data/eastChinaLine.shp
热流文件:            ../data/SHF.csv

🔧 插值引擎就绪


## 6. Target Grid Generation & Unified Interpolation Scheduler

Grid generation strategy: read the union extent of the outline shapefile and the geothermal data, expand outward and round to integer multiples of 0.2°, ensuring all grid point coordinates are integer multiples of 0.2°.

Scheduler notes:
- After interpolation, **special dataset post-processing** is applied automatically (triggered by the `post_process` field)
- Output column names **keep only the data column name** (the dataset name prefix is automatically removed)


In [8]:
# ==================== 6. Target grid generation ====================
def get_target_grid(shapefile_path='../data/eastChinaLine.shp',
                    shf_path='../data/SHF.csv',
                    resolution=0.2):
    """
    Generate the target regular grid from the union extent of the outline shapefile
    and the geothermal data. All grid point coordinates are integer multiples of `resolution`.

    Args:
        shapefile_path: outline shapefile path for East China
        shf_path:       surface heat flow CSV path
        resolution:     grid resolution (degrees), default 0.2°

    Returns:
        target_lats: 1D array, target latitudes (integer multiples of 0.2°)
        target_lons: 1D array, target longitudes (integer multiples of 0.2°)
    """
    import geopandas as gpd

    lat_all = []
    lon_all = []

    # ---- Read the outline shapefile extent ----
    try:
        gdf = gpd.read_file(shapefile_path)
        bounds = gdf.total_bounds  # [minx, miny, maxx, maxy] = [lon_min, lat_min, lon_max, lat_max]
        lat_all.extend([bounds[1], bounds[3]])
        lon_all.extend([bounds[0], bounds[2]])
        print(f"Shapefile 范围: 纬度 [{bounds[1]:.4f}, {bounds[3]:.4f}], 经度 [{bounds[0]:.4f}, {bounds[2]:.4f}]")
    except Exception as e:
        print(f"⚠ 无法读取 shapefile: {e}")

    # ---- Read the geothermal data extent ----
    try:
        df_shf = pd.read_csv(shf_path)
        # Auto-detect lat/lon column names
        lat_col_shf = next((c for c in ['Lat', 'Latitude', 'lat', 'latitude'] if c in df_shf.columns), None)
        lon_col_shf = next((c for c in ['Lon', 'Longitude', 'lon', 'longitude'] if c in df_shf.columns), None)
        if lat_col_shf and lon_col_shf:
            lat_all.extend([df_shf[lat_col_shf].min(), df_shf[lat_col_shf].max()])
            lon_all.extend([df_shf[lon_col_shf].min(), df_shf[lon_col_shf].max()])
            print(f"SHF 范围:     纬度 [{df_shf[lat_col_shf].min():.4f}, {df_shf[lat_col_shf].max():.4f}], "
                  f"经度 [{df_shf[lon_col_shf].min():.4f}, {df_shf[lon_col_shf].max():.4f}]")
        else:
            print(f"⚠ SHF 列名不匹配, 可用列: {list(df_shf.columns)}")
    except Exception as e:
        print(f"⚠ 无法读取 SHF 文件: {e}")

    if len(lat_all) == 0:
        raise ValueError("未能获取任何范围信息，请检查输入文件。")

    # ---- Union extent, expand outward and round to integer multiples of resolution ----
    lat_min_raw = np.min(lat_all)
    lat_max_raw = np.max(lat_all)
    lon_min_raw = np.min(lon_all)
    lon_max_raw = np.max(lon_all)

    print(f"\n并集原始范围:  纬度 [{lat_min_raw:.4f}, {lat_max_raw:.4f}], 经度 [{lon_min_raw:.4f}, {lon_max_raw:.4f}]")

    # Expand to integer multiples of resolution: floor down, ceil up
    lat_min = np.floor(lat_min_raw / resolution) * resolution
    lat_max = np.ceil(lat_max_raw / resolution) * resolution
    lon_min = np.floor(lon_min_raw / resolution) * resolution
    lon_max = np.ceil(lon_max_raw / resolution) * resolution

    # Generate grid points (all integer multiples of resolution)
    target_lats = np.arange(lat_min, lat_max + resolution/2, resolution)
    target_lons = np.arange(lon_min, lon_max + resolution/2, resolution)

    print(f"\n{'='*50}")
    print(f"📐 目标网格 (分辨率 {resolution}°)")
    print(f"{'='*50}")
    print(f"  X 轴 (经度) 范围: [{lon_min:.1f}°, {lon_max:.1f}°]  共 {len(target_lons)} 个点")
    print(f"  Y 轴 (纬度) 范围: [{lat_min:.1f}°, {lat_max:.1f}°]  共 {len(target_lats)} 个点")
    print(f"  网格大小:        {len(target_lats)} × {len(target_lons)} = {len(target_lats) * len(target_lons)} 个点")
    print(f"{'='*50}")

    return target_lats, target_lons


# ==================== Unified interpolation scheduler ====================
def run_interpolation(raster_datasets, config_dict, target_lats, target_lons,
                      variogram_model='spherical', line_datasets=None, **kwargs):
    """
    Process all datasets (raster interpolation + line vector distance computation).

    Args:
        raster_datasets: {name: (df, lat_col, lon_col, value_cols)}   raster data
        config_dict:     DATASET_CONFIG, containing per-dataset configuration
        target_lats:     target latitude array
        target_lons:     target longitude array
        variogram_model: kriging variogram model
        line_datasets:   {name: (geoms, distance_method, output_cols)}   line vector data
        **kwargs:        extra args passed to the specific interpolation functions

    Returns:
        result_df: merged DataFrame
    """
    grid_lon, grid_lat = np.meshgrid(target_lons, target_lats)
    n_points = len(target_lats) * len(target_lons)

    result_df = pd.DataFrame({
        'Latitude':  grid_lat.ravel(),
        'Longitude': grid_lon.ravel(),
    })

    # ---- Process raster / scattered data ----
    for name, (df, lat_col, lon_col, value_cols) in raster_datasets.items():
        cfg = config_dict.get(name, {})
        method = cfg.get('interp_method', 'bilinear')
        pre_filt = cfg.get('kriging_pre_filter', True)
        filt_margin = cfg.get('kriging_filter_margin', 1.0)

        print(f"\n{'='*50}")
        print(f"处理数据集: {name}  (类型: raster, 方法: {method})")
        print(f"{'='*50}")

        for col_idx, value_col in enumerate(value_cols):
            print(f"  [{col_idx+1}/{len(value_cols)}] {value_col} ...", end=" ")

            try:
                if method == 'bilinear':
                    z_grid = bilinear_interpolate(
                        df, lat_col, lon_col, value_col,
                        target_lats, target_lons, **kwargs
                    )
                elif method == 'kriging':
                    z_grid, sigma = kriging_interpolate(
                        df, lat_col, lon_col, value_col,
                        target_lats, target_lons,
                        variogram_model=variogram_model,
                        pre_filter=pre_filt,
                        filter_margin=filt_margin,
                        **kwargs
                    )
                else:
                    raise ValueError(f"未知方法: {method}")

                # ---- Optional post-interpolation smoothing (removes small-scale patches/bullseyes
                #      while keeping regional structure) ----
                # Enabled via config['post_smoothing'], e.g. {'sigma': 1.0} (units: grid cells)
                post_smoothing = cfg.get('post_smoothing', None)
                if post_smoothing is not None and np.isfinite(z_grid).any():
                    _sigma = float(post_smoothing.get('sigma', 1.0))
                    if _sigma > 0:
                        from scipy.ndimage import gaussian_filter
                        _fill = float(np.nanmedian(z_grid))
                        _g = gaussian_filter(np.where(np.isnan(z_grid), _fill, z_grid), sigma=_sigma)
                        z_grid = np.where(np.isnan(z_grid), np.nan, _g)

                # ---- Special dataset post-processing (e.g. LAB invert to positive + m→km) ----
                post_process = cfg.get('post_process', None)
                if post_process is not None:
                    z_grid = apply_special_processing(z_grid, post_process, dataset_name=name)

                # Output column name: keep only the data column name, drop the dataset name prefix
                col_name = make_output_col_name(name, value_col, result_df)
                result_df[col_name] = z_grid.ravel()

                valid_ratio = 1 - result_df[col_name].isna().sum() / n_points
                print(f"✓ 有效数据: {valid_ratio:.1%}")

            except Exception as e:
                print(f"✗ 失败: {e}")

    # ---- Process line vector data ----
    if line_datasets:
        for name, (geoms, dist_method, output_cols) in line_datasets.items():
            print(f"\n{'='*50}")
            print(f"处理数据集: {name}  (类型: line, 方法: {dist_method})")
            print(f"{'='*50}")

            try:
                if dist_method == 'nearest':
                    dist_grid = compute_line_distance(geoms, target_lons, target_lats, method='nearest')
                    dist_grids = [dist_grid]
                    col_names = output_cols[:1]
                elif dist_method == 'top5_mean':
                    dist_grid = compute_line_distance(
                        geoms, target_lons, target_lats, method='top5_mean'
                    )
                    dist_grids = [dist_grid]
                    col_names = output_cols[:1]
                else:
                    raise ValueError(f"未知距离方法: '{dist_method}'")

                for col_name, dist_grid in zip(col_names, dist_grids):
                    col_full = make_output_col_name(name, col_name, result_df)
                    result_df[col_full] = dist_grid.ravel()
                    valid_ratio = 1 - result_df[col_full].isna().sum() / n_points
                    print(f"  {col_name} → {col_full} ✓ 有效数据: {valid_ratio:.1%}")

            except Exception as e:
                print(f"✗ 失败: {e}")

    return result_df


# ==================== 6b. Interpolate to SHF observation points ====================
def compute_line_distance_to_points(geoms, target_lons, target_lats, method='nearest'):
    """
    Compute the distance from **arbitrary point coordinates** to line vector geometries
    (for SHF observation points).

    Args:
        geoms:        list of shapely line geometries
        target_lons:  target point longitude array (1D)
        target_lats:  target point latitude array (1D)
        method:       'nearest' — distance to the nearest line
                      'top5_mean' — mean distance to the top-5 nearest lines

    Returns:
        distances: numpy array with the same shape as target_lons
    """
    from shapely.geometry import Point

    n = len(target_lons)
    dist_arr = np.full(n, np.nan)

    if method == 'nearest':
        for i in range(n):
            pt = Point(target_lons[i], target_lats[i])
            dist_arr[i] = min(pt.distance(g) for g in geoms)
        return dist_arr

    elif method == 'top5_mean':
        for i in range(n):
            pt = Point(target_lons[i], target_lats[i])
            all_dists = sorted(pt.distance(g) for g in geoms)
            dist_arr[i] = np.mean(all_dists[:5]) if len(all_dists) >= 5 else np.mean(all_dists)
        return dist_arr

    else:
        raise ValueError(f"未知距离方法: '{method}'，可选: 'nearest' | 'top5_mean'")


def _smooth_scattered_points(z_pts, lons, lats, sigma=1.0):
    """
    Spatially smooth scattered-point interpolation results (grid round-trip method):
    bilinear-interpolate onto a fine grid covering the scattered extent → Gaussian smooth →
    interpolate back to the scattered positions.
    Used by the `post_smoothing` option of interpolate_to_shf (scattered points are not on a
    regular grid, so a 1D Gaussian smoothing along array order would mix spatially distant points).
    """
    from scipy.ndimage import gaussian_filter
    from scipy.interpolate import griddata, RegularGridInterpolator

    z_pts = np.asarray(z_pts, dtype=float)
    fin = np.isfinite(z_pts)
    if fin.sum() < 4:
        return z_pts

    xs, ys, vs = lons[fin], lats[fin], z_pts[fin]
    if xs.min() == xs.max() or ys.min() == ys.max():
        return z_pts
    n = 100  # fine grid side length (cells); sigma is in "grid cells" (consistent with the grid module)
    xs_new = np.linspace(xs.min(), xs.max(), n)
    ys_new = np.linspace(ys.min(), ys.max(), n)
    lon2d, lat2d = np.meshgrid(xs_new, ys_new)

    g = griddata((xs, ys), vs, (lon2d, lat2d), method='linear')
    if np.isfinite(g).sum() < 4:
        return z_pts
    fill = float(np.nanmedian(g))
    g_s = gaussian_filter(np.where(np.isnan(g), fill, g), sigma=sigma)

    rgi = RegularGridInterpolator((ys_new, xs_new), g_s, bounds_error=False, fill_value=np.nan)
    out = rgi(np.column_stack([lats, lons]))
    # fall back to the original interpolation result where out-of-bounds / unsmoothed
    bad = ~np.isfinite(out)
    out[bad] = z_pts[bad]
    return out


def interpolate_to_shf(raster_datasets, config_dict, shf_df,
                       lat_col_shf='Lat', lon_col_shf='Lon',
                       variogram_model='spherical', line_datasets=None, **kwargs):
    """
    Interpolate all raster datasets to the SHF observation point positions, and compute
    the distances from line vector data to each observation point.

    Args:
        raster_datasets: {name: (df, lat_col, lon_col, value_cols)}   raster data
        config_dict:     DATASET_CONFIG
        shf_df:          surface heat flow DataFrame (contains lat/lon columns)
        lat_col_shf:     SHF latitude column name
        lon_col_shf:     SHF longitude column name
        variogram_model: kriging variogram model
        line_datasets:   {name: (geoms, distance_method, output_cols)}   line vector data
        **kwargs:        extra args passed to the interpolation functions

    Returns:
        result_df: DataFrame based on SHF observation points (raster interpolation columns
                   + line vector distance columns)
    """
    shf_lats = shf_df[lat_col_shf].values
    shf_lons = shf_df[lon_col_shf].values
    n_points = len(shf_lats)

    result_df = shf_df.copy()

    # ---- Process raster / scattered data ----
    for name, (df, lat_col, lon_col, value_cols) in raster_datasets.items():
        cfg = config_dict.get(name, {})
        method = cfg.get('interp_method', 'bilinear')
        pre_filt = cfg.get('kriging_pre_filter', True)
        filt_margin = cfg.get('kriging_filter_margin', 1.0)

        print(f"\n{'='*50}")
        print(f"插值到 SHF 点: {name}  (方法: {method})")
        print(f"{'='*50}")

        for col_idx, value_col in enumerate(value_cols):
            print(f"  [{col_idx+1}/{len(value_cols)}] {value_col} ...", end=" ")

            try:
                if method == 'bilinear':
                    z_interp = bilinear_interpolate_to_points(
                        df, lat_col, lon_col, value_col,
                        shf_lats, shf_lons
                    )
                elif method == 'kriging':
                    # kriging to scattered points (also supports pre-filtering)
                    mask = df[value_col].notna()
                    if pre_filt:
                        grid_lat_min, grid_lat_max = shf_lats.min(), shf_lats.max()
                        grid_lon_min, grid_lon_max = shf_lons.min(), shf_lons.max()
                        bound_lat_min = grid_lat_min - filt_margin
                        bound_lat_max = grid_lat_max + filt_margin
                        bound_lon_min = grid_lon_min - filt_margin
                        bound_lon_max = grid_lon_max + filt_margin
                        spatial_mask = (
                            mask &
                            (df[lat_col] >= bound_lat_min) & (df[lat_col] <= bound_lat_max) &
                            (df[lon_col] >= bound_lon_min) & (df[lon_col] <= bound_lon_max)
                        )
                        n_filt = mask.sum() - spatial_mask.sum()
                        if n_filt > 0:
                            print(f"  🔽 预过滤: 剔除 {n_filt} 个点")
                        mask = spatial_mask

                    if mask.sum() < 4:
                        z_interp = np.full(n_points, np.nan)
                    else:
                        x = df.loc[mask, lon_col].values
                        y = df.loc[mask, lat_col].values
                        z = df.loc[mask, value_col].values
                        OK = OrdinaryKriging(x, y, z, variogram_model=variogram_model,
                                             verbose=False, enable_plotting=False)
                        k_loc = max(4, min(KRIG_N_CLOSEST, len(x)))
                        z_interp, _ = OK.execute('points', shf_lons, shf_lats,
                                                 n_closest_points=k_loc, backend='loop')
                else:
                    raise ValueError(f"未知方法: {method}")

                # ---- Optional post-interpolation smoothing (removes small-scale patches/bullseyes,
                #      keeping regional structure) ----
                # Enabled via config['post_smoothing'], e.g. {'sigma': 1.0}.
                # Note: SHF observation points are scattered (not on a regular grid), so a
                # "grid round-trip" spatial smoothing is used to avoid artifacts from 1D Gaussian
                # smoothing along array order.
                post_smoothing = cfg.get('post_smoothing', None)
                if post_smoothing is not None and np.isfinite(z_interp).any():
                    _sigma = float(post_smoothing.get('sigma', 1.0))
                    if _sigma > 0:
                        z_interp = _smooth_scattered_points(z_interp, shf_lons, shf_lats, sigma=_sigma)

                # ---- Special dataset post-processing (e.g. LAB invert to positive + m→km) ----
                post_process = cfg.get('post_process', None)
                if post_process is not None:
                    z_interp = apply_special_processing(z_interp, post_process, dataset_name=name)

                # Output column name: keep only the data column name, drop the dataset name prefix
                col_name = make_output_col_name(name, value_col, result_df)
                result_df[col_name] = z_interp

                valid_ratio = 1 - np.isnan(z_interp).sum() / n_points
                print(f"✓ 有效数据: {valid_ratio:.1%}")

            except Exception as e:
                print(f"✗ 失败: {e}")

    # ---- Process line vector data (compute distances to SHF observation points) ----
    if line_datasets:
        for name, (geoms, dist_method, output_cols) in line_datasets.items():
            print(f"\n{'='*50}")
            print(f"线矢量距离到 SHF 点: {name}  (方法: {dist_method})")
            print(f"{'='*50}")

            try:
                dist_arr = compute_line_distance_to_points(
                    geoms, shf_lons, shf_lats, method=dist_method
                )
                col_names = output_cols[:1]

                for col_name in col_names:
                    col_full = make_output_col_name(name, col_name, result_df)
                    result_df[col_full] = dist_arr
                    valid_ratio = 1 - np.isnan(dist_arr).sum() / n_points
                    print(f"  {col_name} → {col_full} ✓ 有效数据: {valid_ratio:.1%}")

            except Exception as e:
                print(f"✗ 失败: {e}")

    return result_df


print("✅ 目标网格生成函数和统一调度器已定义")
print("   get_target_grid()              — 读取 shapefile + SHF 并集范围，生成 0.2° 对齐网格")
print("   run_interpolation()            — 栅格插值 + 线矢量距离计算")
print("   compute_line_distance_to_points() — 计算点到线矢量的距离")
print("   interpolate_to_shf()           — 插值到 SHF 观测点（含栅格 + 线矢量距离）")


✅ 目标网格生成函数和统一调度器已定义
   get_target_grid()              — 读取 shapefile + SHF 并集范围，生成 0.2° 对齐网格
   run_interpolation()            — 栅格插值 + 线矢量距离计算
   compute_line_distance_to_points() — 计算点到线矢量的距离
   interpolate_to_shf()           — 插值到 SHF 观测点（含栅格 + 线矢量距离）


## 7. Run Interpolation & Save Results

After preparing the data, uncomment the code below to run. Main workflow:
1. Load all datasets
2. Generate the target grid
3. Batch interpolate onto the grid with the selected methods (including special dataset post-processing, e.g., LAB invert + m→km)
4. Interpolate to the SHF observation points
5. Save the grid results and SHF results
   - Output column names **keep only the data column name** (LAB depth is automatically converted to positive km)


In [9]:
# ==================== 7. Run interpolation ====================

# ---- Step 1: Load data ----
raster_datasets, line_datasets = load_all_datasets(DATASET_CONFIG)

# ---- Step 2: Generate the target grid (shapefile + SHF union extent, 0.2° aligned) ----
target_lats, target_lons = get_target_grid(
    shapefile_path=SHAPEFILE_PATH,
    shf_path=SHF_PATH,
    resolution=TARGET_RESOLUTION,
)

# ---- Step 3: Run interpolation + line distance computation ----
merged_df = run_interpolation(
    raster_datasets,
    config_dict=DATASET_CONFIG,
    target_lats=target_lats,
    target_lons=target_lons,
    variogram_model=VARIOGRAM_MODEL,
    line_datasets=line_datasets,
)

# ---- Step 4: Inspect the grid result ----
print(f"\n{'='*50}")
print(f"网格插值完成！结果形状: {merged_df.shape}")
print(f"列名: {list(merged_df.columns)}")
print(merged_df.head())

# ---- Step 5: Interpolate to SHF observation points ----
df_shf = pd.read_csv(SHF_PATH)
shf_df = interpolate_to_shf(
    raster_datasets,
    config_dict=DATASET_CONFIG,
    shf_df=df_shf,
    variogram_model=VARIOGRAM_MODEL,
    line_datasets=line_datasets,
)

# ---- Step 6: Save ----
output_dir = Path('../output')
output_dir.mkdir(parents=True, exist_ok=True)
merged_df.to_excel(output_dir / f'grid_{TARGET_RESOLUTION}deg.xlsx', index=False)
shf_df.to_excel(output_dir / 'interpolated_to_SHF.xlsx', index=False)
print(f"\n✅ 已保存到: {output_dir}")


  🔍 自动检测纬度列: 'Lat'
  🔍 自动检测经度列: 'Lon'
✓ EMAG [raster]: 13362 条记录, 值列: ['Magnetic_Anomaly_Value(nT)']
  🔍 自动检测纬度列: 'Lat'
  🔍 自动检测经度列: 'Lon'
✓ DEM [raster]: 3336 条记录, 值列: ['DEM']
  🔍 自动检测纬度列: 'Lat'
  🔍 自动检测经度列: 'Lon'
✓ GRD [raster]: 13362 条记录, 值列: ['RASTERVALU']
  🔍 自动检测纬度列: 'Lat'
  🔍 自动检测经度列: 'Lon'
✓ CPD [raster]: 10240 条记录, 值列: ['cpd']
  🔍 自动检测纬度列: 'Lat'
  🔍 自动检测经度列: 'Lon'
✓ LAB [raster]: 16200 条记录, 值列: ['LAB']
✓ Thermal_conductivity [raster]: 1180 条记录, 值列: ['Thermal Conductivity （mW/K/m/）']
  🔍 自动检测纬度列: 'lat'
  🔍 自动检测经度列: 'lon'
✓ CRST1.0 [raster]: 64800 条记录, 值列: ['crsthk', 'sedthk-m', 'bd6', 'bd7', 'bd8', 'bd9', 'ro6', 'ro7', 'ro8', 'ro9', 'vp6', 'vp7', 'vp8', 'vp9', 'vs6', 'vs7', 'vs8', 'vs9']
  🔍 自动检测纬度列: 'Lat'
  🔍 自动检测经度列: 'Lon'
  🔽 离群值过滤[H(km)]: 剔除 15 个点 (method=mad)
✓ CTC [raster]: 4306 条记录, 值列: ['H(km)']
  加载 8995 条线要素 (shp, gpd)
✓ FAULT [line]: 8995 条线要素, 方法: top5_mean
  加载 176 条线要素 (shp, gpd)
✓ ridge [line]: 176 条线要素, 方法: nearest
Shapefile 范围: 纬度 [23.5732, 38.4000], 经度 [113.57

## 8. Result Visualization

Generates spatial distribution maps for each interpolated column, with outline clipping, scale bar, and north arrow.


In [10]:
# ==================== 8. Visualization with outline clipping ====================
import matplotlib.patches as mpatches
import geopandas as gpd
from shapely.geometry import LineString, MultiLineString, Polygon
from shapely.ops import unary_union, polygonize
from matplotlib.ticker import ScalarFormatter
import shapely

# ---- Helpers: scale bar and north arrow ----
def add_scale_bar_line(ax, segment_km=200, line_color='black', fontsize=10):
    xlim = ax.get_xlim(); ylim = ax.get_ylim()
    width = xlim[1] - xlim[0]; height = ylim[1] - ylim[0]
    lat_center = np.mean(ylim)
    km_per_deg = 111.32 * np.cos(np.radians(lat_center))
    seg_deg = segment_km / km_per_deg
    x_start = xlim[0] + 0.05 * width; y_base = ylim[0] + 0.04 * height
    line_h = 0.01 * height
    ax.hlines(y=y_base, xmin=x_start, xmax=x_start+seg_deg, colors=line_color, linewidth=1.5, clip_on=False)
    ax.vlines(x=x_start, ymin=y_base-line_h/2, ymax=y_base+line_h/2, colors=line_color, linewidth=1.5, clip_on=False)
    ax.vlines(x=x_start+seg_deg, ymin=y_base-line_h/2, ymax=y_base+line_h/2, colors=line_color, linewidth=1.5, clip_on=False)
    ax.text(x_start+seg_deg/2, y_base+line_h/2+0.005*height, f'{segment_km} km', ha='center', va='bottom', fontsize=fontsize, clip_on=False)

def add_north_arrow(ax, size_ratio=0.02, fontsize=10):
    xlim = ax.get_xlim(); ylim = ax.get_ylim()
    width = xlim[1]-xlim[0]; height = ylim[1]-ylim[0]
    x0 = xlim[1]-0.06*width; y0 = ylim[1]-0.06*height-0.02*height
    r = size_ratio*height
    ax.add_patch(mpatches.Circle((x0,y0), r, facecolor='white', edgecolor='black', linewidth=1.0, zorder=10, clip_on=False))
    top = y0+0.8*r; bot = y0-0.8*r
    ax.add_patch(mpatches.Polygon([(x0,top),(x0-0.35*r,bot),(x0+0.35*r,bot)], facecolor='black', zorder=11, clip_on=False))
    ax.text(x0, y0+r+0.01*height, 'N', ha='center', va='bottom', fontsize=fontsize, fontweight='bold', clip_on=False)


# ==================== Gray-white terrain basemap (pygmt SRTM15+, optional, as map background) ====================
import matplotlib.colors as _mcolors

class GrayTerrainNorm(_mcolors.Normalize):
    def __init__(self, vland=1500.0, gray_lo=0.5, gray_hi=0.75):
        self.vland, self.gray_lo, self.gray_hi = vland, gray_lo, gray_hi
        super().__init__(vmin=0.0, vmax=vland)
    def __call__(self, value, clip=None):
        v = np.ma.asarray(value, dtype=float)
        out = np.ma.masked_all_like(v)
        sea = v <= 0
        land = v > 0
        if np.any(sea):
            out[sea] = 1.0   # pure white below sea level
        if np.any(land):
            out[land] = self.gray_lo + np.clip(v[land] / self.vland, 0.0, 1.0) * (self.gray_hi - self.gray_lo)
        return out

_gray_norm = GrayTerrainNorm()
_t_cache = {'lon': None, 'lat': None, 'dem': None, 'key': None}

def load_gray_terrain(xmin, xmax, ymin, ymax):
    # Load/cache the gray-white terrain basemap, returning (lon_mesh, lat_mesh, dem);
    # the same region is loaded only once.
    _key = (round(xmin, 3), round(xmax, 3), round(ymin, 3), round(ymax, 3))
    if _t_cache['key'] == _key and _t_cache['dem'] is not None:
        return _t_cache['lon'], _t_cache['lat'], _t_cache['dem']
    try:
        import os as _os
        _env_root = r'C:\Users\19023\anaconda3\envs\KanSHF'
        _os.environ['GDAL_DRIVER_PATH'] = _env_root + r'\Library\lib\gdalplugins'
        _os.environ['PATH'] = (_env_root + r'\Library\bin' + _os.pathsep +
                               _env_root + r'\Library\lib\gdalplugins' + _os.pathsep +
                               _os.environ.get('PATH', ''))
        _tmpdir = r'C:\Users\19023\AppData\Local\Temp'
        _os.makedirs(_tmpdir, exist_ok=True)
        for _k in ('TMPDIR', 'TEMP', 'TMP'):
            _os.environ[_k] = _tmpdir
        import pygmt
        _relief = pygmt.datasets.load_earth_relief(
            resolution='15s', region=[xmin - 1.0, xmax + 1.0, ymin - 0.5, ymax + 0.5], registration=None)
        _step = 5
        _lon, _lat = np.meshgrid(_relief.lon.values[::_step], _relief.lat.values[::_step])
        _dem = _relief.values[::_step, ::_step].astype(float)
        _t_cache['lon'], _t_cache['lat'], _t_cache['dem'], _t_cache['key'] = _lon, _lat, _dem, _key
        print('灰白地形底图: %s' % (str(_dem.shape),))
        return _lon, _lat, _dem
    except Exception as _e:
        print('地形加载失败，跳过地形底图: %s' % _e)
        return None, None, None

def draw_gray_terrain(ax, xmin, xmax, ymin, ymax):
    # Draw the gray-white terrain basemap on the current axes (bottom layer, zorder=0)
    _lon, _lat, _dem = load_gray_terrain(xmin, xmax, ymin, ymax)
    if _dem is not None:
        ax.pcolormesh(_lon, _lat, _dem, cmap='Greys_r', norm=_gray_norm,
                      shading='auto', alpha=0.9, zorder=0)

def plot_interpolated_masked(df, shapefile_path, data_columns=None,
                              n_cols_per_row=4, cmap='RdBu_r',
                              interp_factor=4, save_path=None):
    """
    Plot interpolation results clipped by the shapefile outline, with scale bar and north arrow.

    Args:
        df:              interpolated result DataFrame
        shapefile_path:  outline shapefile path
        data_columns:    columns to plot, None=auto
        n_cols_per_row:  number of subplots per row
        cmap:            colormap
        interp_factor:   smoothing subdivision factor (larger = smoother, default 4)
        save_path:       save path
    """
    # Load the shapefile and build a mask
    gdf = gpd.read_file(shapefile_path)
    union_geom = unary_union(gdf.geometry)
    # Try to build a polygon mask
    mask_polygon = None
    if union_geom.geom_type in ['Polygon', 'MultiPolygon']:
        mask_polygon = union_geom
    elif union_geom.geom_type in ['LineString', 'MultiLineString']:
        polys = list(polygonize(union_geom))
        if polys:
            mask_polygon = unary_union(polys)
        else:
            def force_close(line):
                coords = list(line.coords)
                if len(coords)>1 and coords[0]!=coords[-1]: coords.append(coords[0])
                return LineString(coords)
            if union_geom.geom_type=='LineString':
                closed = force_close(union_geom)
                if closed.is_ring: mask_polygon = Polygon(closed)
            else:
                closed_lines = [force_close(l) for l in union_geom.geoms]
                polys2 = list(polygonize(closed_lines))
                if polys2: mask_polygon = unary_union(polys2)
    if mask_polygon is None:
        mask_polygon = union_geom.convex_hull
    if not mask_polygon.is_valid:
        mask_polygon = mask_polygon.buffer(0)

    # Shapely version compatibility
    sv = tuple(map(int, shapely.__version__.split('.')[:2]))
    if sv >= (2,0):
        from shapely import contains_xy
        def pts_in(poly, xs, ys): return contains_xy(poly, xs, ys)
    else:
        from shapely.vectorized import contains as vec_contains
        def pts_in(poly, xs, ys): return vec_contains(poly, xs, ys)

    # Prepare the data columns
    if data_columns is None:
        data_columns = [c for c in df.columns if c not in ['Latitude', 'Longitude']]
    n_cols = len(data_columns)
    n_rows = int(np.ceil(n_cols / n_cols_per_row))

    fig, axes = plt.subplots(n_rows, n_cols_per_row, figsize=(4.5*n_cols_per_row, 4*n_rows))
    if n_rows == 1:
        axes = axes.reshape(1, -1)
    axes_flat = axes.flatten()

    for idx, col_name in enumerate(data_columns):
        ax = axes_flat[idx]
        plot_data = df[['Longitude', 'Latitude', col_name]].dropna()
        if len(plot_data) == 0:
            ax.text(0.5,0.5,'No data', ha='center', va='center', transform=ax.transAxes)
            ax.set_title(col_name); continue

        # Smoothing subdivision grid
        lons_orig = np.sort(plot_data['Longitude'].unique())
        lats_orig = np.sort(plot_data['Latitude'].unique())
        step = max(np.diff(lons_orig).min() if len(lons_orig)>1 else 0.5,
                   np.diff(lats_orig).min() if len(lats_orig)>1 else 0.5)
        new_step = step / interp_factor
        lons_new = np.arange(lons_orig.min(), lons_orig.max()+new_step, new_step)
        lats_new = np.arange(lats_orig.min(), lats_orig.max()+new_step, new_step)
        lon2d, lat2d = np.meshgrid(lons_new, lats_new)
        points = plot_data[['Longitude', 'Latitude']].values
        values = plot_data[col_name].values
        val_grid = griddata(points, values, (lon2d, lat2d), method='linear')

        # Apply mask clipping
        in_mask = pts_in(mask_polygon, lon2d.ravel(), lat2d.ravel())
        val_grid[~in_mask.reshape(lon2d.shape)] = np.nan

        draw_gray_terrain(ax, lon2d.min(), lon2d.max(), lat2d.min(), lat2d.max())   # gray-white terrain basemap (background)
        mesh = ax.pcolormesh(lon2d, lat2d, val_grid, cmap=cmap, shading='auto', alpha=0.9, zorder=1)
        cbar = plt.colorbar(mesh, ax=ax, shrink=0.7)
        cbar.ax.tick_params(labelsize=10)
        ax.set_title(col_name, fontsize=12)
        ax.set_xlabel('Longitude (°E)', fontsize=9)
        ax.set_ylabel('Latitude (°N)', fontsize=9)
        ax.set_aspect('equal')
        ax.grid(True, linestyle=':', alpha=0.4)

        # Draw the outline
        for geom in gdf.geometry:
            if geom.geom_type in ['Polygon','MultiPolygon']:
                geom = geom.boundary
            if geom.geom_type == 'LineString':
                xb, yb = zip(*geom.coords); ax.plot(xb, yb, 'k-', linewidth=0.8)
            elif geom.geom_type == 'MultiLineString':
                for line in geom.geoms:
                    xb, yb = zip(*line.coords); ax.plot(xb, yb, 'k-', linewidth=0.8)

        add_scale_bar_line(ax, segment_km=200, fontsize=8)
        add_north_arrow(ax, size_ratio=0.018, fontsize=8)

    for idx in range(len(data_columns), len(axes_flat)):
        axes_flat[idx].axis('off')

    plt.suptitle(f'Interpolation Results ({TARGET_RESOLUTION}°, masked)', fontsize=14, y=1.01)
    plt.tight_layout()
    if save_path:
        Path(save_path).parent.mkdir(parents=True, exist_ok=True)
        plt.savefig(save_path, dpi=300, bbox_inches='tight')
        print(f"✅ 图片已保存到: {save_path}")
    plt.show()


print("✅ 带轮廓裁剪的可视化函数已定义")
print("   plot_interpolated_masked() — 带 shapefile 裁剪、比例尺、指北针的绘制")

# ---- Step 7: Plot the spatial distribution maps with outline clipping ----
print("\n生成带轮廓裁剪的可视化图表...")
plot_interpolated_masked(
    merged_df,
    shapefile_path=SHAPEFILE_PATH,
    cmap='RdBu_r',
    save_path=output_dir / 'grid_masked_preview.png',
)


✅ 带轮廓裁剪的可视化函数已定义
   plot_interpolated_masked() — 带 shapefile 裁剪、比例尺、指北针的绘制

生成带轮廓裁剪的可视化图表...
灰白地形底图: (816, 576)
✅ 图片已保存到: ..\output\grid_masked_preview.png


## 9. Usage Instructions

### Quick Start
1. Configure datasets (raster / line vector) in **Cell 2**, specifying the processing method for each
2. For special datasets, configure `post_process` in **Cell 2d** (e.g., LAB invert + m→km)
3. Set global parameters such as the kriging variogram model in **Cell 5**
4. Uncomment **Cell 7** and run the full workflow (grid interpolation + SHF point interpolation)
5. (Optional) Append calls in **Cell 8** to plot the results

### Dual Output Mode
- **Grid output**: all data interpolated onto a 0.2° regular grid (`grid_0.2deg.xlsx`)
- **SHF point output**: all raster data interpolated to SHF observation points + line vector distances (e.g., DTF/DTR), saved as `interpolated_to_SHF.xlsx`

### Output Column Name Rules
- When saving, **only the data column name is kept as the title**, and the dataset name prefix is automatically removed (e.g., `LAB_LAB` → `LAB`)
- If value columns from different datasets share a name, the dataset name is automatically appended as a suffix to distinguish them

### Special Dataset Post-Processing (Cell 2d)
- Add the `post_process` field to a dataset's configuration to enable post-processing
- Built-in processors:
  | Processor | Description |
  |-----------|-------------|
  | `'lab_depth_to_km'` | Invert LAB depth to a positive value, then divide by 1000 to convert the unit from m to km |
- Extend by registering new functions in `SPECIAL_PROCESSORS`

### Two Data Types
| Type | `data_type` | Processing Method | Configuration Fields |
|------|-------------|-------------------|----------------------|
| Raster / scattered | `'raster'` | `interp_method`: `'bilinear'` / `'kriging'` | `kriging_pre_filter`, `kriging_filter_margin`, `post_process` |
| Line vector | `'vector_line'` | `distance_method`: `'nearest'` / `'top5_mean'` | `output_cols` |
> Line vector data (FAULT/ridge, etc.) is output to the grid result and its distance to each SHF observation point is also computed and output to `interpolated_to_SHF.xlsx`.

### Line Vector Distance Methods
- `'nearest'`: outputs 1 column, the Euclidean distance (degrees) from each grid point to the nearest line feature
- `'top5_mean'`: outputs 1 column, the mean distance to the top-5 nearest lines

### Extending with New Datasets
```python
# Raster template
'NEW_RASTER': {
    'data_type': 'raster',
    'path': '...', 'file_type': 'csv',   # csv / xls / xlsx
    # 'lat_col': 'Lat',                  # optional: auto-detected if not specified
    # 'lon_col': 'Lon',                  # optional: auto-detected if not specified
    'value_cols': ['feat1'],
    'interp_method': 'bilinear',
    'kriging_pre_filter': True, 'kriging_filter_margin': 1.0,
    # 'post_process': 'lab_depth_to_km',  # optional: special post-processing
},
# Line vector template
'NEW_LINE': {
    'data_type': 'vector_line',
    'path': '../data/lines.shp',
    'distance_method': 'nearest',   # 'nearest' | 'top5_mean'
    'output_cols': ['DIST'],
},
```


In [11]:
# ==================== 9c. Feature spatial distribution maps (mimics the dataPreprocess example:
#                     outline clipping + scale bar + north arrow) ====================
import matplotlib.patches as mpatches
import geopandas as gpd
from shapely.geometry import Point, Polygon, MultiPolygon, LineString, MultiLineString
from shapely.ops import unary_union, polygonize
from scipy.interpolate import griddata
from matplotlib.ticker import ScalarFormatter
import shapely

plt.rcParams['font.family'] = ['Times New Roman', 'FangSong', 'SimHei', 'Microsoft YaHei']
plt.rcParams['axes.unicode_minus'] = False

GEO_COLS = [
    'Magnetic_Anomaly_Value(nT)', 'DEM', 'RASTERVALU',
    'cpd', 'LAB', 'Thermal Conductivity （mW/K/m/）', 'H(km)', 'DTF',
    'sedthk-m', 'ro6', 'vp7', 'vs8',
    'DTR'
]

# Feature abbreviations (used for subplot titles and colorbar labels, strictly aligned with GEO_COLS)
SHORT_NAMES = [
    'MAG', 'TOPO', 'GRD', 'CPD', 'LAB', 'TC', 'MOHO', 'DTF',
    'ST', 'RO', 'VP', 'VS', 'DTR'
]
assert len(SHORT_NAMES) == len(GEO_COLS), "SHORT_NAMES 数量与 GEO_COLS 不一致"

# ---- Data: 0.2° regular-grid interpolation results ----
try:
    df_grid = merged_df.copy()   # if Cell 7 was already run, use the in-memory variable
except NameError:
    df_grid = pd.read_excel(f'../output/grid_{TARGET_RESOLUTION}deg.xlsx')

# ---- Scale bar and north arrow ----
def add_scale_bar_line(ax, segment_km=200, line_color='black', fontsize=10):
    xlim = ax.get_xlim(); ylim = ax.get_ylim()
    width = xlim[1] - xlim[0]; height = ylim[1] - ylim[0]
    lat_center = np.mean(ylim)
    km_per_deg_lon = 111.32 * np.cos(np.radians(lat_center))
    seg_deg = segment_km / km_per_deg_lon
    x_start = xlim[0] + 0.05 * width; y_base = ylim[0] + 0.04 * height
    line_height = 0.01 * height; line_width = seg_deg
    ax.hlines(y=y_base, xmin=x_start, xmax=x_start + line_width, colors=line_color, linewidth=1.5, clip_on=False)
    ax.vlines(x=x_start, ymin=y_base - line_height/2, ymax=y_base + line_height/2, colors=line_color, linewidth=1.5, clip_on=False)
    ax.vlines(x=x_start + line_width, ymin=y_base - line_height/2, ymax=y_base + line_height/2, colors=line_color, linewidth=1.5, clip_on=False)
    ax.text(x_start + line_width/2, y_base + line_height/2 + 0.005*height,
            f'{segment_km} km', ha='center', va='bottom', fontsize=fontsize, color=line_color, clip_on=False)

def add_north_arrow(ax, size_ratio=0.02, fontsize=10):
    xlim = ax.get_xlim(); ylim = ax.get_ylim()
    width = xlim[1] - xlim[0]; height = ylim[1] - ylim[0]
    margin = 0.06
    x0 = xlim[1] - margin * width; y0 = ylim[1] - margin * height - 0.02 * height
    radius = size_ratio * height; arrow_length = 0.8 * radius
    circle = mpatches.Circle((x0, y0), radius, facecolor='white', edgecolor='black', linewidth=1.0, zorder=10, clip_on=False)
    ax.add_patch(circle)
    arrow_top = y0 + arrow_length; arrow_bottom = y0 - arrow_length
    triangle = mpatches.Polygon([(x0, arrow_top), (x0 - 0.35*radius, arrow_bottom), (x0 + 0.35*radius, arrow_bottom)],
                                facecolor='black', edgecolor='none', zorder=11, clip_on=False)
    ax.add_patch(triangle)
    ax.text(x0, y0 + radius + 0.01*height, 'N', ha='center', va='bottom',
            fontsize=fontsize, fontweight='bold', color='black', clip_on=False)

# ---- Outline mask polygon (no projection transform, consistent with the example) ----
def get_mask_polygon(shapefile_path):
    if not shapefile_path:
        return None, None
    try:
        gdf = gpd.read_file(shapefile_path)
        if gdf.crs is None:
            gdf.crs = 'EPSG:4326'
        union_geom = unary_union(gdf.geometry)
        mask_polygon = None
        if union_geom.geom_type in ['Polygon', 'MultiPolygon']:
            mask_polygon = union_geom
        elif union_geom.geom_type in ['LineString', 'MultiLineString']:
            polygons = list(polygonize(union_geom))
            if polygons:
                mask_polygon = unary_union(polygons)
            else:
                def force_close(line):
                    coords = list(line.coords)
                    if len(coords) > 1 and coords[0] != coords[-1]:
                        coords.append(coords[0])
                    return LineString(coords)
                if union_geom.geom_type == 'LineString':
                    closed = force_close(union_geom)
                    if closed.is_ring:
                        mask_polygon = Polygon(closed)
                else:
                    closed_lines = [force_close(l) for l in union_geom.geoms]
                    polygons2 = list(polygonize(closed_lines))
                    if polygons2:
                        mask_polygon = unary_union(polygons2)
        if mask_polygon is None:
            print("Using convex hull as mask polygon (fallback).")
            mask_polygon = union_geom.convex_hull
        if mask_polygon is not None and not mask_polygon.is_valid:
            mask_polygon = mask_polygon.buffer(0)
            if mask_polygon is not None and not mask_polygon.is_valid:
                mask_polygon = union_geom.convex_hull.buffer(0)
        return mask_polygon, gdf
    except Exception as e:
        print(f"Failed to load contour file: {e}")
        return None, None

mask_polygon, gdf_outline = get_mask_polygon(SHAPEFILE_PATH)

# Shapely version compatibility
sv = tuple(map(int, shapely.__version__.split('.')[:2]))
if sv >= (2, 0):
    from shapely import contains_xy
    def points_in_polygon(polygon, xs, ys): return contains_xy(polygon, xs, ys)
else:
    from shapely.vectorized import contains as vec_contains
    def points_in_polygon(polygon, xs, ys): return vec_contains(polygon, xs, ys)

missing = [c for c in GEO_COLS if c not in df_grid.columns]
if missing:
    raise KeyError(f"数据缺少列: {missing}；可用列: {list(df_grid.columns)}")

UNITS = ['nT', 'm', 'mGal', 'km', 'km', 'mW/K/m', 'km', '°', 'km', 'g/cm³', 'km/s', 'km/s', '°']
INTERP_FACTOR = 4
INTERP_METHOD = 'linear'

n_cols = len(GEO_COLS)
n_rows = int(np.ceil(n_cols / 4))
# ==================== Gray-white terrain basemap (pygmt SRTM15+, optional, as map background) ====================
import matplotlib.colors as _mcolors

class GrayTerrainNorm(_mcolors.Normalize):
    def __init__(self, vland=1500.0, gray_lo=0.5, gray_hi=0.75):
        self.vland, self.gray_lo, self.gray_hi = vland, gray_lo, gray_hi
        super().__init__(vmin=0.0, vmax=vland)
    def __call__(self, value, clip=None):
        v = np.ma.asarray(value, dtype=float)
        out = np.ma.masked_all_like(v)
        sea = v <= 0
        land = v > 0
        if np.any(sea):
            out[sea] = 1.0   # pure white below sea level
        if np.any(land):
            out[land] = self.gray_lo + np.clip(v[land] / self.vland, 0.0, 1.0) * (self.gray_hi - self.gray_lo)
        return out

_gray_norm = GrayTerrainNorm()
_t_cache = {'lon': None, 'lat': None, 'dem': None, 'key': None}

def load_gray_terrain(xmin, xmax, ymin, ymax):
    # Load/cache the gray-white terrain basemap, returning (lon_mesh, lat_mesh, dem);
    # the same region is loaded only once.
    _key = (round(xmin, 3), round(xmax, 3), round(ymin, 3), round(ymax, 3))
    if _t_cache['key'] == _key and _t_cache['dem'] is not None:
        return _t_cache['lon'], _t_cache['lat'], _t_cache['dem']
    try:
        import os as _os
        _env_root = r'C:\Users\19023\anaconda3\envs\KanSHF'
        _os.environ['GDAL_DRIVER_PATH'] = _env_root + r'\Library\lib\gdalplugins'
        _os.environ['PATH'] = (_env_root + r'\Library\bin' + _os.pathsep +
                               _env_root + r'\Library\lib\gdalplugins' + _os.pathsep +
                               _os.environ.get('PATH', ''))
        _tmpdir = r'C:\Users\19023\AppData\Local\Temp'
        _os.makedirs(_tmpdir, exist_ok=True)
        for _k in ('TMPDIR', 'TEMP', 'TMP'):
            _os.environ[_k] = _tmpdir
        import pygmt
        _relief = pygmt.datasets.load_earth_relief(
            resolution='15s', region=[xmin - 1.0, xmax + 1.0, ymin - 0.5, ymax + 0.5], registration=None)
        _step = 5
        _lon, _lat = np.meshgrid(_relief.lon.values[::_step], _relief.lat.values[::_step])
        _dem = _relief.values[::_step, ::_step].astype(float)
        _t_cache['lon'], _t_cache['lat'], _t_cache['dem'], _t_cache['key'] = _lon, _lat, _dem, _key
        print('灰白地形底图: %s' % (str(_dem.shape),))
        return _lon, _lat, _dem
    except Exception as _e:
        print('地形加载失败，跳过地形底图: %s' % _e)
        return None, None, None

def draw_gray_terrain(ax, xmin, xmax, ymin, ymax):
    # Draw the gray-white terrain basemap on the current axes (bottom layer, zorder=0)
    _lon, _lat, _dem = load_gray_terrain(xmin, xmax, ymin, ymax)
    if _dem is not None:
        ax.pcolormesh(_lon, _lat, _dem, cmap='Greys_r', norm=_gray_norm,
                      shading='auto', alpha=0.9, zorder=0)

fig, axes = plt.subplots(n_rows, 4, figsize=(15, n_rows * 4))
if n_rows == 1:
    axes = axes.reshape(1, -1)
axes_flat = axes.flatten()

for idx, col_name in enumerate(GEO_COLS):
    ax = axes_flat[idx]
    plot_data = df_grid[['Longitude', 'Latitude', col_name]].dropna()
    if len(plot_data) == 0:
        ax.text(0.5, 0.5, f'{SHORT_NAMES[idx]}\nNo valid data', ha='center', va='center', transform=ax.transAxes)
        ax.set_title(SHORT_NAMES[idx], fontsize=15)
        ax.set_xlabel('Longitude (°E)', fontsize=18)
        ax.set_ylabel('Latitude (°N)', fontsize=18)
        ax.tick_params(axis='both', labelsize=14)
        continue

    lons_orig = np.sort(plot_data['Longitude'].unique())
    lats_orig = np.sort(plot_data['Latitude'].unique())
    step_lon = np.diff(lons_orig).min() if len(lons_orig) > 1 else 0.5
    step_lat = np.diff(lats_orig).min() if len(lats_orig) > 1 else 0.5
    lons_new = np.arange(lons_orig.min(), lons_orig.max() + step_lon/INTERP_FACTOR, step_lon/INTERP_FACTOR)
    lats_new = np.arange(lats_orig.min(), lats_orig.max() + step_lat/INTERP_FACTOR, step_lat/INTERP_FACTOR)
    lon2d_new, lat2d_new = np.meshgrid(lons_new, lats_new)

    points = plot_data[['Longitude', 'Latitude']].values
    values = plot_data[col_name].values
    value_grid_new = griddata(points, values, (lon2d_new, lat2d_new), method=INTERP_METHOD)

    # Outline clipping
    if mask_polygon is not None:
        in_mask = points_in_polygon(mask_polygon, lon2d_new.ravel(), lat2d_new.ravel())
        value_grid_new[~in_mask.reshape(lon2d_new.shape)] = np.nan

    draw_gray_terrain(ax, lon2d_new.min(), lon2d_new.max(), lat2d_new.min(), lat2d_new.max())   # gray-white terrain basemap (background)
    mesh = ax.pcolormesh(lon2d_new, lat2d_new, value_grid_new, cmap='RdBu_r', shading='auto', alpha=0.9, zorder=1)
    cbar = plt.colorbar(mesh, ax=ax, shrink=0.7)
    cbar.ax.yaxis.set_major_formatter(ScalarFormatter(useMathText=False))
    cbar.ax.yaxis.get_major_formatter().set_scientific(False)
    cbar.ax.yaxis.offsetText.set_visible(False)
    cbar.ax.tick_params(labelsize=12)

    display_name = SHORT_NAMES[idx]   # use the feature abbreviation
    cbar.set_label(f'{display_name} ({UNITS[idx]})', fontsize=12)
    ax.set_title(display_name, fontsize=18)
    ax.set_xlabel('Longitude (°E)', fontsize=14)
    ax.set_ylabel('Latitude (°N)', fontsize=14)
    ax.tick_params(axis='both', labelsize=14)
    ax.set_aspect('equal')
    ax.grid(True, linestyle=':', alpha=0.5)

    label = f'({chr(97 + idx)})'
    ax.text(0.02, 0.98, label, transform=ax.transAxes, fontsize=16, fontweight='bold', va='top', ha='left')

    # Draw the outline
    if gdf_outline is not None:
        for geom in gdf_outline.geometry:
            if geom.is_empty:
                continue
            boundary = geom.boundary
            if boundary.geom_type == 'LineString':
                xb, yb = zip(*boundary.coords)
                ax.plot(xb, yb, color='black', linewidth=1.0)
            elif boundary.geom_type == 'MultiLineString':
                for line in boundary.geoms:
                    xb, yb = zip(*line.coords)
                    ax.plot(xb, yb, color='black', linewidth=1.0)

    add_scale_bar_line(ax, segment_km=200, line_color='black', fontsize=10)
    add_north_arrow(ax, size_ratio=0.02, fontsize=10)

for idx in range(len(GEO_COLS), len(axes_flat)):
    axes_flat[idx].axis('off')

plt.tight_layout(rect=[0, 0, 1, 1], h_pad=0.5)
out_dir = Path('../output/fig/preprocess')
out_dir.mkdir(parents=True, exist_ok=True)
plt.savefig(out_dir / 'GEO_COLS_masked_smoothed_pipeline.png', dpi=300, bbox_inches='tight')
plt.show()
print("✅ 特征空间分布图已保存: ../output/fig/preprocess/GEO_COLS_masked_smoothed_pipeline.png")


灰白地形底图: (819, 576)


✅ 特征空间分布图已保存: ../output/fig/preprocess/GEO_COLS_masked_smoothed_pipeline.png
